# **Medivya v2: Medical Chatbot**

### A. Checking if the Virtual Environment is connected!

In [3]:
print("Environment working fine!")

Environment working fine!


### B. The project begins! 

In [8]:
%pwd

'g:\\SAKSHAM RAJ\\Projects\\Medivya-Medical-Chatbot\\research'

In [9]:
import os 
os.chdir("../")

In [10]:
%pwd

'g:\\SAKSHAM RAJ\\Projects\\Medivya-Medical-Chatbot'

### **1. Extract Documents**
**PDF Loader and Text Splitter**

In [5]:
from langchain.document_loaders import PyPDFLoader, DirectoryLoader
from langchain.text_splitter import RecursiveCharacterTextSplitter

c:\Users\SAKSHAM RAJ\.conda\envs\medivya\lib\site-packages\tqdm\auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [6]:
# Extract text from PDF files
def load_pdf_files(data):
    loader = DirectoryLoader(
        data,
        glob="*.pdf",
        loader_cls=PyPDFLoader
    )

    documents = loader.load()
    return documents

In [ ]:
extracted_data = load_pdf_files("data")
# This step took 10.5 minutes.

In [23]:
extracted_data

[Document(metadata={'producer': 'Adobe PDF Library 9.9; modified using iText® 5.5.6 ©2000-2015 iText Group NV (AGPL-version)', 'creator': 'Adobe InDesign CS5.5 (7.5)', 'creationdate': '2024-06-28T10:57:39+05:30', 'author': '', 'keywords': '', 'moddate': '2024-07-21T08:46:07-05:00', 'subject': '', 'title': '', 'trapped': '/False', 'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf', 'total_pages': 1857, 'page': 0, 'page_label': 'Cover'}, page_content=''),
 Document(metadata={'producer': 'Adobe PDF Library 9.9; modified using iText® 5.5.6 ©2000-2015 iText Group NV (AGPL-version)', 'creator': 'Adobe InDesign CS5.5 (7.5)', 'creationdate': '2024-06-28T10:57:39+05:30', 'author': '', 'keywords': '', 'moddate': '2024-07-21T08:46:07-05:00', 'subject': '', 'title': '', 'trapped': '/False', 'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf', 'total_pages': 1857, 'page': 1, 'page_label': 'Ad'}, page_content=''),
 Document(metadata={'producer': 'Adobe PDF Library 

In [13]:
len(extracted_data)

2494

In [14]:
from typing import List
from langchain.schema import Document

def filter_to_minimal_docs(docs: List[Document]) -> List[Document]:
    """
    Given a list of Document objects, return a new list of Document objects
    containing only 'source' in metadata and the original page_content.
    """
    minimal_docs: List[Document] = []
    for doc in docs:
        src = doc.metadata.get("source")
        minimal_docs.append(
            Document(
                page_content=doc.page_content,
                metadata={"source": src}
            )
        )
    return minimal_docs

In [15]:
minimal_docs = filter_to_minimal_docs(extracted_data)

In [16]:
minimal_docs

[Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content=''),
 Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content=''),
 Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content=''),
 Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content='2025\nCURRENT\nMedical Diagnosis \n& Treatment\nSIXTY-FOURTH EDITION\nEdited by\na LANGE medical book\nMaxine A. Papadakis, MD \nProfessor of Medicine, Emeritus \nDepartment of Medicine\nUniversity of California, San Francisco\nMichael W. Rabow, MD \nProfessor of Medicine and Urology\nDivision of Palliative Medicine\nDepartment of Medicine\nUniversity of California, San Francisco\nAssociate Editor\nMonica Gandhi, MD, MPH \nProfessor of Medicine\xa0\nDivision of HIV, ID, and Global Medicine \nSan Francisco General Hospital\nUniversity of California, San Francisco

### **2. Chunking**

In [17]:
# Split the documents into smaller chunks

def text_split(minimal_docs):
    text_splitter = RecursiveCharacterTextSplitter(
        chunk_size=500,
        chunk_overlap=20,
    )
    
    texts_chunk = text_splitter.split_documents(minimal_docs)
    return texts_chunk

In [18]:
texts_chunk = text_split(minimal_docs)
print(f"Number of chunks: {len(texts_chunk)}")
print("Number of chunk:" , len(texts_chunk))

Number of chunks: 27484
Number of chunk: 27484


Now, the documents has been converted into chunks and each chunk will have 500 tokens.

In [19]:
texts_chunk

[Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content='2025\nCURRENT\nMedical Diagnosis \n& Treatment\nSIXTY-FOURTH EDITION\nEdited by\na LANGE medical book\nMaxine A. Papadakis, MD \nProfessor of Medicine, Emeritus \nDepartment of Medicine\nUniversity of California, San Francisco\nMichael W. Rabow, MD \nProfessor of Medicine and Urology\nDivision of Palliative Medicine\nDepartment of Medicine\nUniversity of California, San Francisco\nAssociate Editor\nMonica Gandhi, MD, MPH \nProfessor of Medicine\xa0\nDivision of HIV, ID, and Global Medicine'),
 Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment-2025-1.pdf'}, page_content='San Francisco General Hospital\nUniversity of California, San Francisco\nWith Contributing Authors\nKenneth R. McQuaid, MD \nProfessor of Medicine \nDepartment of Medicine\nUniversity of California, San Francisco'),
 Document(metadata={'source': 'data\\current-medical-diagnosis-and-treatment

### **3. Embeddings**

In [20]:
from langchain.embeddings import HuggingFaceEmbeddings

def download_embeddings():
    # Download the embeddings model from HuggingFace and return the embeddings object.

    model_name = "sentence-transformers/all-MiniLM-L6-v2"
    #  We can change this to any other model available on HuggingFace
    embeddings = HuggingFaceEmbeddings(
        model_name=model_name
    )
    return embeddings

embedding = download_embeddings()

C:\Users\SAKSHAM RAJ\AppData\Local\Temp\ipykernel_16064\3728361049.py:8: LangChainDeprecationWarning: The class `HuggingFaceEmbeddings` was deprecated in LangChain 0.2.2 and will be removed in 1.0. An updated version of the class exists in the :class:`~langchain-huggingface package and should be used instead. To use it run `pip install -U :class:`~langchain-huggingface` and import as `from :class:`~langchain_huggingface import HuggingFaceEmbeddings``.
  embeddings = HuggingFaceEmbeddings(


In [21]:
embedding

HuggingFaceEmbeddings(client=SentenceTransformer(
  (0): Transformer({'max_seq_length': 256, 'do_lower_case': False}) with Transformer model: BertModel 
  (1): Pooling({'word_embedding_dimension': 384, 'pooling_mode_cls_token': False, 'pooling_mode_mean_tokens': True, 'pooling_mode_max_tokens': False, 'pooling_mode_mean_sqrt_len_tokens': False, 'pooling_mode_weightedmean_tokens': False, 'pooling_mode_lasttoken': False, 'include_prompt': True})
  (2): Normalize()
), model_name='sentence-transformers/all-MiniLM-L6-v2', cache_folder=None, model_kwargs={}, encode_kwargs={}, multi_process=False, show_progress=False)

In [25]:
vector = embedding.embed_query("Hello world")
vector

# # This is the vector representation of the query "Hello, how are you doctor?" using the embeddings model.

[-0.03447732329368591,
 0.031023172661662102,
 0.006734992377460003,
 0.02610897459089756,
 -0.039361998438835144,
 -0.16030246019363403,
 0.06692395359277725,
 -0.006441502366214991,
 -0.04745049774646759,
 0.014758813194930553,
 0.07087533175945282,
 0.05552756041288376,
 0.01919337548315525,
 -0.026251375675201416,
 -0.010109520517289639,
 -0.026940494775772095,
 0.022307440638542175,
 -0.02222665213048458,
 -0.1496925801038742,
 -0.017493028193712234,
 0.007676287554204464,
 0.0543522983789444,
 0.003254436422139406,
 0.03172590956091881,
 -0.0846213772892952,
 -0.029405979439616203,
 0.05159560963511467,
 0.04812411218881607,
 -0.003314825939014554,
 -0.058279216289520264,
 0.041969314217567444,
 0.022210657596588135,
 0.128188818693161,
 -0.022338952869176865,
 -0.01165623776614666,
 0.06292832642793655,
 -0.03287627920508385,
 -0.09122603386640549,
 -0.031175361946225166,
 0.0526994951069355,
 0.047034814953804016,
 -0.0842030942440033,
 -0.030056126415729523,
 -0.02074483595788

In [26]:
print( "Vector length:", len(vector))

# 384 is the length of the vector returned by the model "sentence-transformers/all-MiniLM-L6-v2"

Vector length: 384


### **4. API Keys setup**

In [27]:
from dotenv import load_dotenv
import os
load_dotenv()

True

In [28]:
PINECONE_API_KEY=os.getenv("PINECONE_API_KEY")
GEMINI_API_KEY=os.getenv("GEMINI_API_KEY")

os.environ["PINECONE_API_KEY"]=PINECONE_API_KEY
os.environ["GEMINI_API_KEY"] = GEMINI_API_KEY

### **5. Pinecone Vector DB**

Pinecone Account Authorisation

In [29]:
from pinecone import Pinecone 
pinecone_api_key = PINECONE_API_KEY

pc = Pinecone(api_key=pinecone_api_key)

In [30]:
pc

In [ ]:
import requests

# Paste actual key directly here as a string to check if the key is valid. 
# If the key is valid, a 200 status code will be returned.
test_key = "***********************************"

url = "https://api.pinecone.io/indexes"
headers = {
    "Api-Key": test_key,
    "Content-Type": "application/json"
}

response = requests.get(url, headers=headers)

print(f"Status Code: {response.status_code}")
print(f"Response: {response.text}")

Status Code: 200
Response: {"indexes":[]}


Pinecone Index related information

In [ ]:
from pinecone import Pinecone, ServerlessSpec 

pc = Pinecone(api_key=pinecone_api_key)

index_name = "medivya-chatbot"

if not pc.has_index(index_name):
    pc.create_index(
        name = index_name,
        dimension = 384,  # Dimension of the embeddings
        metric = "cosine",  # Cosine similarity
        spec = ServerlessSpec(cloud="aws", region="us-east-1")
    )

index = pc.Index(index_name)
print("✅ Successfully connected and initialized the index!")

✅ Successfully connected and initialized the index!


In [ ]:
# from pinecone import ServerlessSpec 

# index_name = "medivya-chatbot"

# if not pc.has_index(index_name):
#     pc.create_index(
#         name = index_name,
#         dimension = 384,  # Dimension of the embeddings
#         metric = "cosine",  # Cosine similarity
#         spec = ServerlessSpec(cloud="aws", region="us-east-1")
#     )


# index = pc.Index(index_name)

Pinecone index being saved to the cloud. **Time consuming - 2 hrs for 3 PDFs or 40 mts for 2 or 10 mts for 1**

In [ ]:
from langchain_pinecone import PineconeVectorStore

docsearch = PineconeVectorStore.from_documents(
    documents=texts_chunk,
    embedding=embedding,
    index_name=index_name
)

Load Existing Index

In [ ]:
# Load Existing index 

from langchain_pinecone import PineconeVectorStore
# Embed each chunk and upsert the embeddings into your Pinecone index.
docsearch = PineconeVectorStore.from_existing_index(
    index_name=index_name,
    embedding=embedding
)

Add more data to the existing Pinecone Index

In [ ]:
# Add more data to the existing Pinecone Index

dswith = Document(
    page_content = "Hello, this chatbot has been trained on medical data and can answer questions related to various medical conditions, symptoms, and treatments.",
    metadata = {"source": "Medical Books"}
)

In [ ]:
docsearch.add_documents(documents=[dswith])

['090ef8b1-4a6e-4700-bb21-d2fe96a79ac9']

### **6. Retriever**

In document format

In [ ]:
retriever = docsearch.as_retriever(search_type="similarity", search_kwargs={"k":3})
# This will return the top 3 most similar documents to the query.

In [ ]:
retrieved_docs = retriever.invoke("What is ANTICOAGULATION?")
retrieved_docs

[Document(id='b5f795ad-4f0d-4cb4-af92-6b3c8633e357', metadata={'source': 'data\\Medical_book.pdf'}, page_content='anticoagulant. Anticoagulants stop the blood from clot-\nting. In the laboratory, the tube of blood spins at high\nspeed within a machine called a centrifuge. The blood\ncells sink to the bottom and the liquid stays on the top.\nThis straw-colored liquid on the top is the plasma. To\nmeasure the glucose, a person’s plasma is combined with\nother substances. From the resulting reaction, the amount\nof glucose in the plasma is determined.\nOral glucose tolerance test'),
 Document(id='169fa5de-a2cc-4d73-8c3d-1156036e4810', metadata={'source': 'data\\Medical_book.pdf'}, page_content='vessel.\nThrombin—Thrombin is a protein produced by the\nbody. It is a specific clotting factor that plays an\nimportant role in the blood clotting process.\nThrombin inhibitor —Thrombin inhibitors are one\ntype of anticoagulant medication, used to help pre-\nvent formation of harmful blood clots i

In [ ]:
retrieved_docs = retriever.invoke("What to do in case of Abdominal upset after eating oily food?")
retrieved_docs

[Document(id='0860a666-eb55-40ac-81d3-5a4f93dd44e3', metadata={'source': 'data\\Medical_book.pdf'}, page_content='green vegetables, apples, and pears are a few examples of\nhigh residue foods. Many patients will benefit from\nadding bulk preparations of psyllium. Constipating foods\nlike bananas and cheese should be avoided until a natural\nrhythm is well established.\nTo assure that stools are soft enough to pass easily, it\nis a good idea to add a pure stool softener like DOSS\n(dioctyl sodium sulfosuccinate), two to four per day as\nneeded. DOSS also helps prevent impaction.'),
 Document(id='7d167cee-8e7d-4e8d-9a63-b3ea7bb2e47a', metadata={'source': 'data\\Medical_book.pdf'}, page_content='highly refined foods have eliminated most of the residue\nfrom food. The result is that most food is absorbed, leav-\ning little to pass through and be excreted as feces.\n• Constipation occurs acutely with impaction—the pres-\nence in the rectum of a mass of feces too large to pass.\nFecal impact

### **7. Retriever - LLM Connectivity**

Using Gemini API for chat model

In [ ]:
from langchain.chains import create_retrieval_chain
from langchain.chains.combine_documents import create_stuff_documents_chain
from langchain_core.prompts import ChatPromptTemplate

In [ ]:
system_prompt = """You are Medivya, an expert, professional medical AI assistant. Your primary goal is to provide accurate, objective, and detailed medical answers based strictly on the provided context.
Use the following pieces of retrieved context to answer the question. You will be provided with context from a medical document and a question.

### Response Rules:
1. STRICT GROUNDING: If the context does not contain the exact information needed to answer the question, or if the context is ambiguous, you must immediately respond with: 'I am not able to answer this question based on the provided context.' Do not guess, hallucinate, or infer outside the text.
2. STRUCTURED FORMAT: Provide a comprehensive answer formatted exactly with the following sections:
   - **Summary:** A clear 1-2 sentence direct answer to the user's medical related question in 25-35 words.
   - **Detailed Findings:** Use bullet points to comprehensively list all relevant facts, symptoms, treatments, procedures, or evidence explicitly mentioned in the context in maximum of 50 words.

{context}"""

prompt = ChatPromptTemplate.from_messages(
    [
        ("system", system_prompt),
        ("human", "{input}"  )
    ]
)

In [ ]:
from langchain_google_genai import ChatGoogleGenerativeAI
import os

# Initialize the Gemini chat model as a LangChain object
chatModel = ChatGoogleGenerativeAI(
    model="gemini-3.1-flash-lite",
    google_api_key=os.getenv("GEMINI_API_KEY"),
    max_retries=0,  # Forces 
)

### **8. Retriever - RAG Chain**

In [ ]:
question_answer_chain = create_stuff_documents_chain(chatModel, prompt)
rag_chain = create_retrieval_chain(retriever, question_answer_chain)

In [ ]:
import time

print("Starting retrieval and generation...")
start_time = time.time()

# 1. Test Retriever Speed
retriever_start = time.time()
docs = retriever.invoke("what is Acromegaly and gigantism?")
print(f"Retriever took: {time.time() - retriever_start:.2f} seconds")

# 2. Test Full Chain Speed
chain_start = time.time()
response = rag_chain.invoke({"input": "what is Acromegaly and gigantism?"})
print(f"LLM Generation took: {time.time() - chain_start:.2f} seconds")

print(f"Total execution time: {time.time() - start_time:.2f} seconds")

Starting retrieval and generation...
Retriever took: 0.42 seconds
LLM Generation took: 2.08 seconds
Total execution time: 2.50 seconds


In [ ]:
response = rag_chain.invoke({"input": "what is Acromegaly and gigantism?"})
print(response["answer"])

**Summary:**
Acromegaly and gigantism are disorders involving excessive pituitary growth hormone release, causing abnormal tissue and bone growth; gigantism involves unusual height, while acromegaly occurs after bone growth has typically ceased in adulthood.

**Detailed Findings:**
* Acromegaly results from abnormal pituitary chemical release causing bone and soft tissue growth.
* Gigantism is characterized by unusual height.
* Acromegaly affects 50 per million people.
* Symptoms occur gradually, often delaying diagnosis until middle age.
* Both men and women are affected by these disorders.


In [ ]:
response = rag_chain.invoke({"input": "what is Acne?"})
print(response["answer"])

**Summary:**
Acne is a prevalent skin disorder characterized by pimples appearing on the chest, back, and face, occurring when skin pores become obstructed by bacteria, dead skin cells, and accumulated skin oil.

**Detailed Findings:**
*   Acne vulgaris is the medical term for common acne.
*   It is a skin disease where sebaceous glands become inflamed.
*   The condition affects nearly 17 million people in the United States.
*   It is characterized by the clogging of skin pores with oil, bacteria, and dead skin cells.


In [ ]:
response = rag_chain.invoke({"input": "what is the Treatment of Acne?"})
print(response["answer"])

**Summary:**
Treatment for acne depends on its severity and involves topical drugs like tretinoin, benzoyl peroxide, or antibiotics, while severe cases may require oral isotretinoin to achieve improvement over several months of use.

**Detailed Findings:**
*   Mild noninflammatory acne: Treated with topical tretinoin, benzoyl peroxide, adapalene, or salicylic acid to reduce comedones.
*   Inflammatory acne: May require topical antibiotics or oral isotretinoin.
*   Procedures/Care: Gentle daily washing, avoiding abrasive cleansers, and using noncomedogenic products can help minimize flare-ups. Improvement typically takes weeks to months.


In [ ]:
response = rag_chain.invoke({"input": "what is Water?"})
print(response["answer"])

**Summary:**
Water is a vital substance that enters the body through food and drink and is produced by cellular chemical reactions, while being continuously excreted via urine, sweat, feces, and breath vapor.

**Detailed Findings:**
* Water intake occurs through food and drink consumption.
* It is generated internally by cellular chemical reactions.
* The body loses water through urine, sweat, feces, and breath as water vapor.
* ADH release helps maintain optimal bodily water levels during increased blood serum concentration or decreased blood volume.


In [ ]:
response = rag_chain.invoke({"input": "what is medivya?"})
print(response["answer"])

**Summary:**
Medivya is an expert, professional medical AI assistant trained on medical data, designed to provide accurate, objective, and detailed answers to questions regarding various medical conditions, symptoms, and treatments for users.

**Detailed Findings:**
*   Medivya functions as an AI chatbot.
*   The assistant is trained on medical data.
*   Its primary goal is providing accurate, objective, and detailed medical information.
*   It addresses topics including medical conditions, symptoms, and treatments.
*   Responses are generated based strictly on provided medical context.


In [ ]:
response = rag_chain.invoke({"input": "What is diabetes and how is it treated?"})
print(response["answer"])

**Summary:**
Diabetes mellitus is a condition where the body produces insufficient or ineffective insulin, leading to high blood sugar levels known as hyperglycemia, which requires early diagnosis and management to prevent organ damage.

**Detailed Findings:**
* Diabetes involves either insufficient insulin production or ineffective insulin function.
* Untreated diabetes can damage eyes, kidneys, nerves, heart, and blood vessels.
* Antidiabetic drugs are used to control blood sugar levels.
* Early diagnosis is essential to prevent organ failure.
* Hypoglycemia may be identified through blood sugar testing.


In [ ]:
print("Medivya: ", end="")

# .pick("answer") isolates just the LLM's text output and forces a true token stream
answer_stream = rag_chain.pick("answer").stream({"input": "what is Acromegaly and gigantism?"})

for chunk in answer_stream:
    print(chunk, end="", flush=True)

Medivya: **Summary:**
Acromegaly and gigantism are disorders caused by the abnormal release of growth hormone from the pituitary gland, leading to excessive bone and soft tissue growth and various systemic bodily disturbances.

**Detailed Findings:**
* Acromegaly occurs when growth hormone abnormality happens after bone growth stops.
* Gigantism occurs when this abnormality results in unusual height.
* The condition is rare, affecting 50 per 1,000,000 people.
* Symptoms develop gradually, often delaying diagnosis until patients reach middle age.
* Both men and women are affected.

In [ ]:
response = rag_chain.invoke({"input": "what is this chatbot been trained on?"})
print(response["answer"])

**Summary:**
This chatbot has been specifically trained on medical data to provide professional and objective information regarding various medical conditions, symptoms, and treatments for users seeking assistance with their health-related inquiries.

**Detailed Findings:**
*   The chatbot is trained on medical data.
*   It is designed to answer questions related to:
    *   Various medical conditions.
    *   Symptoms.
    *   Treatments.
*   The chatbot is named Medivya and functions as an expert, professional medical AI assistant.
